# Learned Stage-Wise Curvature Tuning on OCTMNIST

This notebook evaluates Learned Stage-Wise Curvature Tuning (SW-CT) on the OCTMNIST dataset using an ImageNet-pretrained ResNet-18.

OCTMNIST is a medical image-classification dataset containing retinal optical coherence tomography images. Its visual domain differs substantially from the natural images used during ImageNet pretraining, providing a strong domain-shift setting for evaluating Learned SW-CT.

The experiments compare four conditions:

1. **Baseline** — the original pretrained ResNet with ReLU activations and a trained downstream classifier.
2. **Single-Parameter Curvature Tuning (S-CT)** — one global beta selected through validation-based exhaustive search.
3. **Learned SW-CT with fixed initialization** — four trainable stage-wise beta parameters initialized at 0.78.
4. **Learned SW-CT with random initialization** — four trainable stage-wise beta parameters independently initialized between 0.70 and 0.99.

Each condition is evaluated using seeds 42, 43, and 44.

Experiments are conducted for both 20 and 30 epochs to determine whether additional optimization improves performance or changes the learned stage-wise beta values.

Wall-clock execution time is also recorded to compare computational cost across Baseline, S-CT, and Learned SW-CT.

In [1]:
!nvidia-smi

Sat Oct  3 09:07:48 2026       
+-----------------------------------------------------------------------------------------+
| NVIDIA-SMI 580.178.04             Driver Version: 580.178.04     CUDA Version: 13.0     |
+-----------------------------------------+------------------------+----------------------+
| GPU  Name                 Persistence-M | Bus-Id          Disp.A | Volatile Uncorr. ECC |
| Fan  Temp   Perf          Pwr:Usage/Cap |           Memory-Usage | GPU-Util  Compute M. |
|                                         |                        |               MIG M. |
|=========================================+========================+======================|
|   0  Tesla T4                       Off |   00000000:00:1E.0 Off |                    0 |
| N/A   26C    P8             13W /   70W |       0MiB /  15360MiB |      0%      Default |
|                                         |                        |                  N/A |
+-----------------------------------------+-----

In [2]:
%cd /content

!git clone -b main \
    https://github.com/NiftySnek173/research-curvature-tuning.git

%cd /content/research-curvature-tuning/src/curvature-tuning

!git branch --show-current
!git log -1 --oneline

/home/zeus/miniconda3/envs/cloudspace/lib/python3.12/site-packages/IPython/core/magics/osm.py:417: UserWarning: using dhist requires you to install the `pickleshare` library.
  self.shell.db['dhist'] = compress_dhist(dhist)[-100:]


/content


Cloning into 'curvature-tuning-research'...

/content/curvature-tuning-research/src/curvature-tuning
stage-wise-ct
068c466 (HEAD -> stage-wise-ct, origin/stage-wise-ct, origin/HEAD) Updated aircraft with complete results


## Environment Setup

The repository dependencies are installed before running the experiments.

After installation, the Colab runtime should be restarted so that the required package versions are loaded correctly.

In [3]:
%pip install -q -r requirements.txt
%pip install --force-reinstall --no-cache-dir "numpy==1.26.3"

Note: you may need to restart the kernel to use updated packages.
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 18.0/18.0 MB 251.5 MB/s  0:00:00
  Attempting uninstall: numpy
    Found existing installation: numpy 1.26.3
    Uninstalling numpy-1.26.3:
      Successfully uninstalled numpy-1.26.3
Note: you may need to restart the kernel to use updated packages.


In [1]:
%cd /content/research-curvature-tuning/src/curvature-tuning

import os
import torch

os.environ["WANDB_MODE"] = "disabled"

print("Working directory:", os.getcwd())
print("PyTorch:", torch.__version__)
print("CUDA available:", torch.cuda.is_available())

if torch.cuda.is_available():
    print("GPU:", torch.cuda.get_device_name(0))

/home/zeus/miniconda3/envs/cloudspace/lib/python3.12/site-packages/IPython/core/magics/osm.py:417: UserWarning: using dhist requires you to install the `pickleshare` library.
  self.shell.db['dhist'] = compress_dhist(dhist)[-100:]


/content/curvature-tuning-research/src/curvature-tuning
Working directory: /content/curvature-tuning-research/src/curvature-tuning
PyTorch: 2.8.0+cu128
CUDA available: True
GPU: Tesla T4


## OCTMNIST Dataset

Before running the experiments, the OCTMNIST data loaders are checked to confirm that the downstream dataset can be loaded correctly.

The same dataset split and random seed protocol are used for Baseline, S-CT, and Learned SW-CT so that the methods are compared under the same conditions.

In [2]:
from utils.data import get_data_loaders

train_loader, test_loader, val_loader = get_data_loaders(
    "imagenet_to_medmnist/octmnist",
    train_batch_size=32,
    test_batch_size=128,
    seed=42,
)

print("Train samples:", len(train_loader.dataset))
print("Validation samples:", len(val_loader.dataset))
print("Test samples:", len(test_loader.dataset))

images, labels = next(iter(train_loader))

print("Image batch shape:", images.shape)
print("Label batch shape:", labels.shape)
print("Labels:", labels[:10])

README.md:   0%|          | 0.00/7.32k [00:00<?, ?B/s]

medmnist.py:   0%|          | 0.00/4.84k [00:00<?, ?B/s]

Generating train split: 0 examples [00:00, ? examples/s]

Generating test split: 0 examples [00:00, ? examples/s]

Generating validation split: 0 examples [00:00, ? examples/s]

Train samples: 97477
Validation samples: 10832
Test samples: 1000
Image batch shape: torch.Size([32, 3, 224, 224])
Label batch shape: torch.Size([32])
Labels: tensor([0, 0, 0, 3, 0, 0, 3, 0, 2, 0])


# ResNet-18 Experiments

ResNet-18 is evaluated first because it was used during the initial development of Learned SW-CT.

The experiment compares Baseline, S-CT, fixed-initialization SW-CT, and random-initialization SW-CT.

All methods use the same ImageNet-pretrained backbone, OCTMNIST dataset split, experimental seeds, and downstream training protocol.

## ResNet-18 — 20-Epoch Evaluation

The first evaluation uses 20 training epochs.

This provides the primary reference experiment and maintains compatibility with the earlier Learned SW-CT work.

### Methods

**Baseline**

The pretrained ResNet-18 retains its original ReLU activations. The backbone is frozen and only the downstream classifier is trained.

**S-CT**

The original Single-Parameter Curvature Tuning method searches over a single beta shared throughout the network. Candidate beta values from 0.70 to 1.00 are evaluated using validation performance, and the best candidate is evaluated on the test set.

The recorded S-CT execution time includes the complete beta search rather than only the final selected beta.

**Learned SW-CT — Fixed Initialization**

Four trainable beta parameters are assigned to the four ResNet stages. All four begin at beta = 0.78.

This preserves the initialization used in the original Learned SW-CT experiments.

**Learned SW-CT — Random Initialization**

Four trainable stage-wise beta parameters are initialized independently between 0.70 and 0.99.

The random initialization is generated deterministically from the experiment seed. This allows the experiment to test whether Learned SW-CT depends on the fixed 0.78 starting value while remaining reproducible.

In [3]:
!CUDA_VISIBLE_DEVICES=1 WANDB_MODE=disabled python generalization_ct.py \
    --model resnet18 \
    --pretrained_ds imagenet \
    --transfer_ds medmnist/octmnist \
    --seed 42 \
    --linear_probe_train_bs 32 \
    --linear_probe_test_bs 128 \
    --epochs 20

2026-10-02 08:54:13.806 | INFO     | __main__:main:74 - Log file: ./logs/generalization_ct_imagenet_to_medmnist-octmnist_resnet18_seed42_epochs20.log
2026-10-02 08:54:13.808 | INFO     | __main__:main:78 - Running on cuda
2026-10-02 08:54:19.758 | INFO     | __main__:main:105 - Testing baseline...
2026-10-02 08:54:19.785 | INFO     | __main__:main:116 - Number of trainable parameters: 2052
2026-10-02 08:54:19.785 | INFO     | __main__:main:117 - Starting transfer learning...
2026-10-02 08:56:48.439 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 1.416570, Accuracy: 46.88%
2026-10-02 08:56:48.755 | INFO     | train:train_epoch:47 - Epoch 1, Step 100, Loss: 1.284457, Accuracy: 46.04%
2026-10-02 08:56:49.052 | INFO     | train:train_epoch:47 - Epoch 1, Step 200, Loss: 1.216078, Accuracy: 51.32%
2026-10-02 08:56:49.341 | INFO     | train:train_epoch:47 - Epoch 1, Step 300, Loss: 1.156229, Accuracy: 56.01%
2026-10-02 08:56:49.637 | INFO     | train:train_epoch:47 - Epoch 1, Step 

In [4]:
!CUDA_VISIBLE_DEVICES=1 WANDB_MODE=disabled python generalization_ct.py \
    --model resnet18 \
    --pretrained_ds imagenet \
    --transfer_ds medmnist/octmnist \
    --seed 43 \
    --linear_probe_train_bs 32 \
    --linear_probe_test_bs 128 \
    --epochs 20

2026-10-02 12:38:31.096 | INFO     | __main__:main:74 - Log file: ./logs/generalization_ct_imagenet_to_medmnist-octmnist_resnet18_seed43_epochs20.log
2026-10-02 12:38:31.098 | INFO     | __main__:main:78 - Running on cuda
2026-10-02 12:38:36.872 | INFO     | __main__:main:105 - Testing baseline...
2026-10-02 12:38:36.899 | INFO     | __main__:main:116 - Number of trainable parameters: 2052
2026-10-02 12:38:36.899 | INFO     | __main__:main:117 - Starting transfer learning...
2026-10-02 12:41:11.047 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 1.177475, Accuracy: 59.38%
2026-10-02 12:41:11.355 | INFO     | train:train_epoch:47 - Epoch 1, Step 100, Loss: 1.161288, Accuracy: 55.14%
2026-10-02 12:41:11.672 | INFO     | train:train_epoch:47 - Epoch 1, Step 200, Loss: 1.117259, Accuracy: 58.26%
2026-10-02 12:41:11.966 | INFO     | train:train_epoch:47 - Epoch 1, Step 300, Loss: 1.085530, Accuracy: 60.74%
2026-10-02 12:41:12.269 | INFO     | train:train_epoch:47 - Epoch 1, Step 

In [5]:
!CUDA_VISIBLE_DEVICES=1 WANDB_MODE=disabled python generalization_ct.py \
    --model resnet18 \
    --pretrained_ds imagenet \
    --transfer_ds medmnist/octmnist \
    --seed 44 \
    --linear_probe_train_bs 32 \
    --linear_probe_test_bs 128 \
    --epochs 20

2026-10-02 16:28:59.512 | INFO     | __main__:main:74 - Log file: ./logs/generalization_ct_imagenet_to_medmnist-octmnist_resnet18_seed44_epochs20.log
2026-10-02 16:28:59.515 | INFO     | __main__:main:78 - Running on cuda
2026-10-02 16:29:05.360 | INFO     | __main__:main:105 - Testing baseline...
2026-10-02 16:29:05.377 | INFO     | __main__:main:116 - Number of trainable parameters: 2052
2026-10-02 16:29:05.377 | INFO     | __main__:main:117 - Starting transfer learning...
2026-10-02 16:31:39.564 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 0.973706, Accuracy: 56.25%
2026-10-02 16:31:39.912 | INFO     | train:train_epoch:47 - Epoch 1, Step 100, Loss: 1.247779, Accuracy: 43.16%
2026-10-02 16:31:40.255 | INFO     | train:train_epoch:47 - Epoch 1, Step 200, Loss: 1.205179, Accuracy: 46.00%
2026-10-02 16:31:40.602 | INFO     | train:train_epoch:47 - Epoch 1, Step 300, Loss: 1.152011, Accuracy: 51.65%
2026-10-02 16:31:40.948 | INFO     | train:train_epoch:47 - Epoch 1, Step 

### Learned SW-CT with Fixed Beta Initialization

The original Learned SW-CT configuration is first reproduced using the fixed initialization:

\[[\beta_1,\beta_2,\beta_3,\beta_4]=[0.78,0.78,0.78,0.78].\]

The initial value is only a starting point. During training, the four beta parameters are optimized independently together with the downstream classifier.

These runs provide the reference against which random initialization will be compared.

In [4]:
!WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet18 \
    --pretrained_ds imagenet \
    --transfer_ds medmnist/octmnist \
    --seed 42 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy fixed \
    --init_beta 0.78 \
    --beta_lr 0.01 \
    --epochs 20

2026-10-03 09:19:57.329 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_medmnist-octmnist_resnet18_seed42_epochs20_initfixed0.78_betalr0.01.log
2026-10-03 09:19:57.391 | INFO     | __main__:main:302 - Running on cuda
2026-10-03 09:19:58.357 | INFO     | __main__:main:389 - Initialization strategy: fixed
2026-10-03 09:19:58.357 | INFO     | __main__:main:394 - Requested initial stage betas: [0.78, 0.78, 0.78, 0.78]
Stage-Wise CT ReLU counts: [3, 2, 2, 2]
2026-10-03 09:19:58.398 | INFO     | __main__:main:418 - Initial stage betas: [0.7799999713897705, 0.7799999713897705, 0.7799999713897705, 0.7799999713897705]
2026-10-03 09:19:58.398 | INFO     | __main__:main:434 - Trainable curvature parameters: 4
2026-10-03 09:19:58.398 | INFO     | __main__:main:439 - Total trainable parameters: 2056
2026-10-03 09:19:59.624 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 1.291399, Accuracy: 37.50%
2026-10-03 09:20:14.406 | INFO     | train:train_e

In [5]:
!WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet18 \
    --pretrained_ds imagenet \
    --transfer_ds medmnist/octmnist \
    --seed 43 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy fixed \
    --init_beta 0.78 \
    --beta_lr 0.01 \
    --epochs 20

2026-10-03 11:57:57.454 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_medmnist-octmnist_resnet18_seed43_epochs20_initfixed0.78_betalr0.01.log
2026-10-03 11:57:57.525 | INFO     | __main__:main:302 - Running on cuda
2026-10-03 11:57:58.664 | INFO     | __main__:main:389 - Initialization strategy: fixed
2026-10-03 11:57:58.664 | INFO     | __main__:main:394 - Requested initial stage betas: [0.78, 0.78, 0.78, 0.78]
Stage-Wise CT ReLU counts: [3, 2, 2, 2]
2026-10-03 11:57:58.691 | INFO     | __main__:main:418 - Initial stage betas: [0.7799999713897705, 0.7799999713897705, 0.7799999713897705, 0.7799999713897705]
2026-10-03 11:57:58.691 | INFO     | __main__:main:434 - Trainable curvature parameters: 4
2026-10-03 11:57:58.691 | INFO     | __main__:main:439 - Total trainable parameters: 2056
2026-10-03 11:57:59.446 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 1.575276, Accuracy: 12.50%
2026-10-03 11:58:14.265 | INFO     | train:train_e

In [6]:
!WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet18 \
    --pretrained_ds imagenet \
    --transfer_ds medmnist/octmnist \
    --seed 44 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy fixed \
    --init_beta 0.78 \
    --beta_lr 0.01 \
    --epochs 20

2026-10-03 14:36:25.695 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_medmnist-octmnist_resnet18_seed44_epochs20_initfixed0.78_betalr0.01.log
2026-10-03 14:36:25.769 | INFO     | __main__:main:302 - Running on cuda
2026-10-03 14:36:26.845 | INFO     | __main__:main:389 - Initialization strategy: fixed
2026-10-03 14:36:26.846 | INFO     | __main__:main:394 - Requested initial stage betas: [0.78, 0.78, 0.78, 0.78]
Stage-Wise CT ReLU counts: [3, 2, 2, 2]
2026-10-03 14:36:26.872 | INFO     | __main__:main:418 - Initial stage betas: [0.7799999713897705, 0.7799999713897705, 0.7799999713897705, 0.7799999713897705]
2026-10-03 14:36:26.873 | INFO     | __main__:main:434 - Trainable curvature parameters: 4
2026-10-03 14:36:26.873 | INFO     | __main__:main:439 - Total trainable parameters: 2056
2026-10-03 14:36:27.708 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 1.864022, Accuracy: 21.88%
2026-10-03 14:36:42.622 | INFO     | train:train_e

### Learned SW-CT with Random Beta Initialization

The fixed beta = 0.78 initialization may raise the question of whether Learned SW-CT performs well only because its starting point was informed by the earlier S-CT experiments.

To test this dependency, each of the four stage-wise beta parameters is now initialized independently from a uniform distribution between 0.70 and 0.99.

The initialization is reproducible: the random generator is seeded using the experiment seed. Therefore, each seed always receives the same initial beta vector.

If random initialization produces similar performance to the fixed 0.78 experiment, this provides evidence that the Learned SW-CT result is not dependent on a single hand-selected initialization.

In [7]:
!WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet18 \
    --pretrained_ds imagenet \
    --transfer_ds medmnist/octmnist \
    --seed 42 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy random \
    --beta_lr 0.01 \
    --epochs 20

2026-10-03 17:15:00.137 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_medmnist-octmnist_resnet18_seed42_epochs20_initrandom_betalr0.01.log
2026-10-03 17:15:00.200 | INFO     | __main__:main:302 - Running on cuda
2026-10-03 17:15:01.559 | INFO     | __main__:main:389 - Initialization strategy: random
2026-10-03 17:15:01.559 | INFO     | __main__:main:394 - Requested initial stage betas: [0.924447, 0.827275, 0.948993, 0.902237]
Stage-Wise CT ReLU counts: [3, 2, 2, 2]
2026-10-03 17:15:01.587 | INFO     | __main__:main:418 - Initial stage betas: [0.924447238445282, 0.827274739742279, 0.9489933848381042, 0.9022367000579834]
2026-10-03 17:15:01.588 | INFO     | __main__:main:434 - Trainable curvature parameters: 4
2026-10-03 17:15:01.588 | INFO     | __main__:main:439 - Total trainable parameters: 2056
2026-10-03 17:15:02.464 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 1.344671, Accuracy: 37.50%
2026-10-03 17:15:17.329 | INFO     | t

In [8]:
!WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet18 \
    --pretrained_ds imagenet \
    --transfer_ds medmnist/octmnist \
    --seed 43 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy random \
    --beta_lr 0.01 \
    --epochs 20

2026-10-03 19:53:11.812 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_medmnist-octmnist_resnet18_seed43_epochs20_initrandom_betalr0.01.log
2026-10-03 19:53:11.872 | INFO     | __main__:main:302 - Running on cuda
2026-10-03 19:53:12.862 | INFO     | __main__:main:389 - Initialization strategy: random
2026-10-03 19:53:12.863 | INFO     | __main__:main:394 - Requested initial stage betas: [0.889167, 0.712695, 0.705809, 0.943372]
Stage-Wise CT ReLU counts: [3, 2, 2, 2]
2026-10-03 19:53:12.888 | INFO     | __main__:main:418 - Initial stage betas: [0.8891667127609253, 0.7126947641372681, 0.7058085799217224, 0.9433716535568237]
2026-10-03 19:53:12.888 | INFO     | __main__:main:434 - Trainable curvature parameters: 4
2026-10-03 19:53:12.889 | INFO     | __main__:main:439 - Total trainable parameters: 2056
2026-10-03 19:53:13.742 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 1.565119, Accuracy: 15.62%
2026-10-03 19:53:28.570 | INFO     |

In [9]:
!WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet18 \
    --pretrained_ds imagenet \
    --transfer_ds medmnist/octmnist \
    --seed 44 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy random \
    --beta_lr 0.01 \
    --epochs 20

2026-10-03 22:30:44.606 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_medmnist-octmnist_resnet18_seed44_epochs20_initrandom_betalr0.01.log
2026-10-03 22:30:44.664 | INFO     | __main__:main:302 - Running on cuda
2026-10-03 22:30:45.892 | INFO     | __main__:main:389 - Initialization strategy: random
2026-10-03 22:30:45.893 | INFO     | __main__:main:394 - Requested initial stage betas: [0.735544, 0.774853, 0.817674, 0.981063]
Stage-Wise CT ReLU counts: [3, 2, 2, 2]
2026-10-03 22:30:45.919 | INFO     | __main__:main:418 - Initial stage betas: [0.7355440258979797, 0.7748528122901917, 0.8176735043525696, 0.9810633659362793]
2026-10-03 22:30:45.920 | INFO     | __main__:main:434 - Trainable curvature parameters: 4
2026-10-03 22:30:45.920 | INFO     | __main__:main:439 - Total trainable parameters: 2056
2026-10-03 22:30:46.775 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 1.843215, Accuracy: 25.00%
2026-10-03 22:31:01.629 | INFO     |

# ResNet-18 — 30-Epoch Evaluation

The same experiments are now repeated for 30 epochs.

The purpose of increasing the training budget is to determine whether the 20-epoch results are limited by insufficient optimization.

If a method improves substantially with 30 epochs, this suggests that additional optimization is useful. If performance remains similar, it indicates that the method has largely stabilized within the original 20-epoch training budget.

All other experimental settings remain unchanged.

For random-initialization SW-CT, the same seed produces exactly the same initial four-beta vector in both the 20-epoch and 30-epoch experiments. Therefore, initialization is held constant while the training duration changes.

Execution time is again recorded to measure the computational cost of extending training from 20 to 30 epochs.

In [10]:
!WANDB_MODE=disabled python generalization_ct.py \
    --model resnet18 \
    --pretrained_ds imagenet \
    --transfer_ds medmnist/octmnist \
    --seed 42 \
    --linear_probe_train_bs 32 \
    --linear_probe_test_bs 128 \
    --epochs 30

2026-10-04 01:08:05.911 | INFO     | __main__:main:74 - Log file: ./logs/generalization_ct_imagenet_to_medmnist-octmnist_resnet18_seed42_epochs30.log
2026-10-04 01:08:05.913 | INFO     | __main__:main:78 - Running on cuda
2026-10-04 01:08:06.995 | INFO     | __main__:main:105 - Testing baseline...
2026-10-04 01:08:07.012 | INFO     | __main__:main:116 - Number of trainable parameters: 2052
2026-10-04 01:08:07.012 | INFO     | __main__:main:117 - Starting transfer learning...
2026-10-04 01:10:23.039 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 1.416569, Accuracy: 46.88%
2026-10-04 01:10:23.400 | INFO     | train:train_epoch:47 - Epoch 1, Step 100, Loss: 1.284457, Accuracy: 46.04%
2026-10-04 01:10:23.652 | INFO     | train:train_epoch:47 - Epoch 1, Step 200, Loss: 1.216078, Accuracy: 51.32%
2026-10-04 01:10:23.864 | INFO     | train:train_epoch:47 - Epoch 1, Step 300, Loss: 1.156229, Accuracy: 56.01%
2026-10-04 01:10:24.090 | INFO     | train:train_epoch:47 - Epoch 1, Step 

In [11]:
!WANDB_MODE=disabled python generalization_ct.py \
    --model resnet18 \
    --pretrained_ds imagenet \
    --transfer_ds medmnist/octmnist \
    --seed 43 \
    --linear_probe_train_bs 32 \
    --linear_probe_test_bs 128 \
    --epochs 30

2026-10-04 05:50:53.393 | INFO     | __main__:main:74 - Log file: ./logs/generalization_ct_imagenet_to_medmnist-octmnist_resnet18_seed43_epochs30.log
2026-10-04 05:50:53.395 | INFO     | __main__:main:78 - Running on cuda
2026-10-04 05:50:54.597 | INFO     | __main__:main:105 - Testing baseline...
2026-10-04 05:50:54.612 | INFO     | __main__:main:116 - Number of trainable parameters: 2052
2026-10-04 05:50:54.612 | INFO     | __main__:main:117 - Starting transfer learning...
2026-10-04 05:53:10.500 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 1.177475, Accuracy: 59.38%
2026-10-04 05:53:10.756 | INFO     | train:train_epoch:47 - Epoch 1, Step 100, Loss: 1.161288, Accuracy: 55.14%
2026-10-04 05:53:11.097 | INFO     | train:train_epoch:47 - Epoch 1, Step 200, Loss: 1.117259, Accuracy: 58.26%
2026-10-04 05:53:11.491 | INFO     | train:train_epoch:47 - Epoch 1, Step 300, Loss: 1.085530, Accuracy: 60.74%
2026-10-04 05:53:11.906 | INFO     | train:train_epoch:47 - Epoch 1, Step 

In [12]:
!WANDB_MODE=disabled python generalization_ct.py \
    --model resnet18 \
    --pretrained_ds imagenet \
    --transfer_ds medmnist/octmnist \
    --seed 44 \
    --linear_probe_train_bs 32 \
    --linear_probe_test_bs 128 \
    --epochs 30

2026-10-04 10:20:46.689 | INFO     | __main__:main:74 - Log file: ./logs/generalization_ct_imagenet_to_medmnist-octmnist_resnet18_seed44_epochs30.log
2026-10-04 10:20:46.691 | INFO     | __main__:main:78 - Running on cuda
2026-10-04 10:20:47.867 | INFO     | __main__:main:105 - Testing baseline...
2026-10-04 10:20:47.882 | INFO     | __main__:main:116 - Number of trainable parameters: 2052
2026-10-04 10:20:47.882 | INFO     | __main__:main:117 - Starting transfer learning...
2026-10-04 10:23:04.787 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 0.973706, Accuracy: 56.25%
2026-10-04 10:23:05.027 | INFO     | train:train_epoch:47 - Epoch 1, Step 100, Loss: 1.247779, Accuracy: 43.16%
2026-10-04 10:23:05.351 | INFO     | train:train_epoch:47 - Epoch 1, Step 200, Loss: 1.205179, Accuracy: 46.00%
2026-10-04 10:23:05.571 | INFO     | train:train_epoch:47 - Epoch 1, Step 300, Loss: 1.152011, Accuracy: 51.65%
2026-10-04 10:23:05.846 | INFO     | train:train_epoch:47 - Epoch 1, Step 

In [13]:
!WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet18 \
    --pretrained_ds imagenet \
    --transfer_ds medmnist/octmnist \
    --seed 42 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy fixed \
    --init_beta 0.78 \
    --beta_lr 0.01 \
    --epochs 30

2026-10-04 14:53:21.574 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_medmnist-octmnist_resnet18_seed42_epochs30_initfixed0.78_betalr0.01.log
2026-10-04 14:53:21.640 | INFO     | __main__:main:302 - Running on cuda
2026-10-04 14:53:22.738 | INFO     | __main__:main:389 - Initialization strategy: fixed
2026-10-04 14:53:22.738 | INFO     | __main__:main:394 - Requested initial stage betas: [0.78, 0.78, 0.78, 0.78]
Stage-Wise CT ReLU counts: [3, 2, 2, 2]
2026-10-04 14:53:22.764 | INFO     | __main__:main:418 - Initial stage betas: [0.7799999713897705, 0.7799999713897705, 0.7799999713897705, 0.7799999713897705]
2026-10-04 14:53:22.765 | INFO     | __main__:main:434 - Trainable curvature parameters: 4
2026-10-04 14:53:22.765 | INFO     | __main__:main:439 - Total trainable parameters: 2056
2026-10-04 14:53:23.580 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 1.291399, Accuracy: 37.50%
2026-10-04 14:53:38.360 | INFO     | train:train_e

In [14]:
!WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet18 \
    --pretrained_ds imagenet \
    --transfer_ds medmnist/octmnist \
    --seed 43 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy fixed \
    --init_beta 0.78 \
    --beta_lr 0.01 \
    --epochs 30

2026-10-04 18:49:56.917 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_medmnist-octmnist_resnet18_seed43_epochs30_initfixed0.78_betalr0.01.log
2026-10-04 18:49:56.977 | INFO     | __main__:main:302 - Running on cuda
2026-10-04 18:49:58.108 | INFO     | __main__:main:389 - Initialization strategy: fixed
2026-10-04 18:49:58.109 | INFO     | __main__:main:394 - Requested initial stage betas: [0.78, 0.78, 0.78, 0.78]
Stage-Wise CT ReLU counts: [3, 2, 2, 2]
2026-10-04 18:49:58.150 | INFO     | __main__:main:418 - Initial stage betas: [0.7799999713897705, 0.7799999713897705, 0.7799999713897705, 0.7799999713897705]
2026-10-04 18:49:58.150 | INFO     | __main__:main:434 - Trainable curvature parameters: 4
2026-10-04 18:49:58.151 | INFO     | __main__:main:439 - Total trainable parameters: 2056
2026-10-04 18:49:58.967 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 1.575276, Accuracy: 12.50%
2026-10-04 18:50:13.843 | INFO     | train:train_e

In [15]:
!WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet18 \
    --pretrained_ds imagenet \
    --transfer_ds medmnist/octmnist \
    --seed 44 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy fixed \
    --init_beta 0.78 \
    --beta_lr 0.01 \
    --epochs 30

2026-10-04 22:46:33.912 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_medmnist-octmnist_resnet18_seed44_epochs30_initfixed0.78_betalr0.01.log
2026-10-04 22:46:33.971 | INFO     | __main__:main:302 - Running on cuda
2026-10-04 22:46:34.929 | INFO     | __main__:main:389 - Initialization strategy: fixed
2026-10-04 22:46:34.930 | INFO     | __main__:main:394 - Requested initial stage betas: [0.78, 0.78, 0.78, 0.78]
Stage-Wise CT ReLU counts: [3, 2, 2, 2]
2026-10-04 22:46:34.955 | INFO     | __main__:main:418 - Initial stage betas: [0.7799999713897705, 0.7799999713897705, 0.7799999713897705, 0.7799999713897705]
2026-10-04 22:46:34.956 | INFO     | __main__:main:434 - Trainable curvature parameters: 4
2026-10-04 22:46:34.956 | INFO     | __main__:main:439 - Total trainable parameters: 2056
2026-10-04 22:46:35.786 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 1.864022, Accuracy: 21.88%
2026-10-04 22:46:50.567 | INFO     | train:train_e

In [16]:
!WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet18 \
    --pretrained_ds imagenet \
    --transfer_ds medmnist/octmnist \
    --seed 42 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy random \
    --beta_lr 0.01 \
    --epochs 30

2026-10-05 02:42:47.256 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_medmnist-octmnist_resnet18_seed42_epochs30_initrandom_betalr0.01.log
2026-10-05 02:42:47.338 | INFO     | __main__:main:302 - Running on cuda
2026-10-05 02:42:48.368 | INFO     | __main__:main:389 - Initialization strategy: random
2026-10-05 02:42:48.369 | INFO     | __main__:main:394 - Requested initial stage betas: [0.924447, 0.827275, 0.948993, 0.902237]
Stage-Wise CT ReLU counts: [3, 2, 2, 2]
2026-10-05 02:42:48.394 | INFO     | __main__:main:418 - Initial stage betas: [0.924447238445282, 0.827274739742279, 0.9489933848381042, 0.9022367000579834]
2026-10-05 02:42:48.395 | INFO     | __main__:main:434 - Trainable curvature parameters: 4
2026-10-05 02:42:48.395 | INFO     | __main__:main:439 - Total trainable parameters: 2056
2026-10-05 02:42:49.125 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 1.344671, Accuracy: 37.50%
2026-10-05 02:43:03.920 | INFO     | t

In [17]:
!WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet18 \
    --pretrained_ds imagenet \
    --transfer_ds medmnist/octmnist \
    --seed 43 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy random \
    --beta_lr 0.01 \
    --epochs 30

2026-10-05 06:39:08.300 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_medmnist-octmnist_resnet18_seed43_epochs30_initrandom_betalr0.01.log
2026-10-05 06:39:08.365 | INFO     | __main__:main:302 - Running on cuda
2026-10-05 06:39:09.383 | INFO     | __main__:main:389 - Initialization strategy: random
2026-10-05 06:39:09.383 | INFO     | __main__:main:394 - Requested initial stage betas: [0.889167, 0.712695, 0.705809, 0.943372]
Stage-Wise CT ReLU counts: [3, 2, 2, 2]
2026-10-05 06:39:09.409 | INFO     | __main__:main:418 - Initial stage betas: [0.8891667127609253, 0.7126947641372681, 0.7058085799217224, 0.9433716535568237]
2026-10-05 06:39:09.409 | INFO     | __main__:main:434 - Trainable curvature parameters: 4
2026-10-05 06:39:09.409 | INFO     | __main__:main:439 - Total trainable parameters: 2056
2026-10-05 06:39:10.140 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 1.565119, Accuracy: 15.62%
2026-10-05 06:39:24.968 | INFO     |

In [18]:
!WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet18 \
    --pretrained_ds imagenet \
    --transfer_ds medmnist/octmnist \
    --seed 44 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy random \
    --beta_lr 0.01 \
    --epochs 30

2026-10-05 10:35:15.354 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_medmnist-octmnist_resnet18_seed44_epochs30_initrandom_betalr0.01.log
2026-10-05 10:35:15.413 | INFO     | __main__:main:302 - Running on cuda
2026-10-05 10:35:16.471 | INFO     | __main__:main:389 - Initialization strategy: random
2026-10-05 10:35:16.472 | INFO     | __main__:main:394 - Requested initial stage betas: [0.735544, 0.774853, 0.817674, 0.981063]
Stage-Wise CT ReLU counts: [3, 2, 2, 2]
2026-10-05 10:35:16.497 | INFO     | __main__:main:418 - Initial stage betas: [0.7355440258979797, 0.7748528122901917, 0.8176735043525696, 0.9810633659362793]
2026-10-05 10:35:16.497 | INFO     | __main__:main:434 - Trainable curvature parameters: 4
2026-10-05 10:35:16.498 | INFO     | __main__:main:439 - Total trainable parameters: 2056
2026-10-05 10:35:17.223 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 1.843215, Accuracy: 25.00%
2026-10-05 10:35:31.991 | INFO     |